In [1]:
import re
import spacy
import html
import os
import random
import json

def split_sentences(nlp, text):
    """
    Splits the given text into sentences using spaCy's sentence segmenter.
    """
    doc = nlp(text)
    return [sent.text for sent in doc.sents]

def read_and_process_json_sections(json_file, nlp):
    global skipped_file
    """
    Reads a JSON file, processes sections into sentences, and maps mentions to sentences.
    """
    with open(json_file, "r", encoding="utf-8") as file:
        data = json.load(file)

    # Process each page in the JSON data
    final_data = []
    for page_id, page_content in enumerate(data['pages']):
        print(f"\033[91mProcessing\033[0m Page ID: {page_id}")

        # Clean the content by replacing </p> with a space and removing <p> tags
        cleaned_content = re.sub(r'<\/?p>', '', page_content)
        cleaned_content = re.sub(r'[\r\n]+', '', cleaned_content)
        cleaned_content = re.sub(r'[\r\n\u21B5]+', ' ', page_content)

        # Extract entities from annotations
        entities = []
        for annotation in data['annotations']:
            if annotation['relationships']['date']['page']== page_id:
                start = annotation['textContext']['start']
                end = annotation['textContext']['end']
                entity_type = annotation['label'].lower()
                if entity_type in ["cdrug","sdrug"]:
                    entity_type = "drug"
                if entity_type in ["mae"]:
                    entity_type = "ae"
                mention_text = cleaned_content[start:end]
                # Append the entity tuple
                entities.append({
                    "start": start,
                    "end": end,
                    "type": entity_type,
                    "text": annotation['textContext']['text']
                })
                

        # Order entities based on the value of start
        entities = sorted(entities, key=lambda x: x['start'])
        print(f"Entities: {entities}")

        # Split the section into sentences
        sentences = split_sentences(nlp, cleaned_content)

        sentence_start = 0
        entity_index = 0  # Index to track the current entity being processed
        num_entities = len(entities)

        for sentence in sentences:
            sentence_end = sentence_start + len(sentence)
            sentence_entities = []

            # Process entities that belong to the current sentence
            while entity_index < num_entities and entities[entity_index]["start"] >= sentence_start and entities[entity_index]["end"] <= sentence_end:
                entity = entities[entity_index]
                # print(f"Entity: {entity}")
                # Calculate relative start and end positions in the sentence
                relative_start = entity["start"] - sentence_start
                relative_end = entity["end"] - sentence_start
                entity_text = entity["text"]
                start = sentence.find(entity_text)

                # Validate that the extracted text matches the entity text
                if start != -1:
                    end = start + len(entity_text)
                    entity_type = entity["type"]
                    global unique_entity_types
                    global entity_type_counts
                    unique_entity_types.add(entity_type)
                    if entity_type in entity_type_counts:
                        entity_type_counts[entity_type] += 1
                    else:
                        entity_type_counts[entity_type] = 1
                    print("sucessfully get the entity!!")
                    # if entity["type"] != "R/O" and entity["type"] != "sDx" and entity["type"] != "SYM" and entity["type"] != "Dx":
                    #     if entity["type"] in ["sDrug","cDrug", "drug"]:
                    #         sentence_entities.append((start, end, "Drug"))
                    #         print(f"\033[91mchanged to Drug: {entity['type']} at ({start}, {end}), and the word is {entity_text}\033[0m")
                    #     elif entity["type"] == "mAE" or entity["type"] == "ae":
                    #         sentence_entities.append((start, end, "AE"))
                    #         print(f"\033[91mchanged to AE: {entity['type']} at ({start}, {end}, and the word is {entity_text})\033[0m")
                    #     else:
                    #         sentence_entities.append((start, end, entity_type))
                    # else:
                    #     # print(f"\033[93mskip these entities: {entity['type']} at ({start}, {end})\033[0m")
                    #     skipped_file += 1
                        # print(f"skip these entities: {entity["type"]} at ({start}, {end})")
                    # sentence_entities.append((start, end, entity_type))
                    # sentence_entities.append((start, end, entity_type, entity_text))
                    # print(f"Entity matched: {entity_text} at ({start}, {end})")
                else:
                    print(
                        f"\033[93mWarning: Text mismatch for entity '{entity_text}' in {sentence} "
                        f"at indices ({relative_start}, {relative_end}).\033[0m" 
                    )

                # Move to the next entity
                entity_index += 1

            # Add the sentence and its entities to the labeled data
            if sentence_entities:
                final_data.append((sentence, {"entities": sentence_entities}))
                # print(f"\033[92mmatched Sentence: {sentence}\033[0m")
                # print(f"\033[92mmatched Entities: {sentence_entities}\033[0m")

            # Update the sentence_start for the next sentence
            if sentence_start + len(sentence) < len(cleaned_content) and cleaned_content[sentence_start + len(sentence)] == ' ':
                sentence_start = sentence_end + 1  # Account for the space/newline between sentences
            else:
                sentence_start = sentence_end

    return final_data

def get_file_list(folder_path):
    """
    Get a list of all JSON files in a folder.
    """
    return [os.path.join(folder_path, file) for file in os.listdir(folder_path) if file.endswith(".json")]


def split_file_list(file_list, train_ratio=0.8):
    """
    Split the list of files into train and test datasets.
    """
    random.seed(123)
    random.shuffle(file_list)
    split_idx = int(len(file_list) * train_ratio)
    return file_list[:split_idx], file_list[split_idx:]

def process_files(file_list, nlp):
    """
    Process JSON files into spaCy-compatible training data.
    """
    processed_data = []
    for json_file in file_list:
        print(f"\033[91mProcessing\033[0m file: {json_file}")
        processed_data.extend(read_and_process_json_sections(json_file, nlp))
    return processed_data
unique_entity_types = set()
entity_type_counts = {}
# Example usage
folder_path = 'C:/Users/Wenjuan.Zhang/OneDrive - FDA/Documents/Latest Annotation 07182025/FAERS_R1'  # Replace with your folder path
file_list = get_file_list(folder_path)



# Split into train and test datasets
train_files, test_files = split_file_list(file_list)

##########################################
# 读取 true_files.txt
with open("C:/Users/Wenjuan.Zhang/Downloads/true_files.txt", "r", encoding="utf-8") as f:
    true_files = [line.strip() for line in f if line.strip()]  # 去掉换行/空行

cleaned_list = [os.path.splitext(os.path.basename(f))[0] for f in train_files]
print(cleaned_list)
# 过滤 file_list
indices = [i for i, f in enumerate(cleaned_list) if f in train_files]
train_files_matched = [train_files[i] for i in indices]

print(f"共有 {len(train_files_matched)} 个文件符合条件")
print(train_files_matched)



cleaned_list = [os.path.splitext(os.path.basename(f))[0] for f in test_files]
print(cleaned_list)
# 过滤 file_list
indices = [i for i, f in enumerate(cleaned_list) if f in test_files]
test_files_matched = [test_files[i] for i in indices]

print(f"共有 {len(test_files_matched)} 个文件符合条件")
print(test_files_matched)

###############################################

# Load a spaCy language model for sentence splitting
nlp = spacy.blank("en")
nlp.add_pipe("sentencizer")  # Add sentence segmenter
skipped_file = 0
# Process train and test files
train_data = process_files(train_files_matched, nlp)
test_data = process_files(test_files_matched, nlp)
print(test_files)
print(f"Skipped files: {skipped_file}")
# Output a sample from the formatted data
for sample in train_data[:3]:  # Display first 3 samples
    print(sample)
# Sort and print all unique entity types
sorted_unique_entity_types = sorted(unique_entity_types)
print(f"\033[92mUnique Entity Types: {sorted_unique_entity_types}\033[0m")
sorted_entity_type_counts = sorted(entity_type_counts.items())

# Print each key-value pair on a new line, separated by commas
for entity_type, count in sorted_entity_type_counts:
    print(f"{entity_type}: {count}")



['14726257-mengjie', '6-64-mengjie', 'mengjie-4-38', '2-453-mengjie', '8-89-mengjie', '2-8-mengjie', '17429608-mengjie', '2-11-mengjie', '6462817-mengjie', '6-180-mengjie', '6-189-mengjie', '8-97-mengjie', '6-21-mengjie', 'mengjie-4-129', '8-69-mengjie', 'mengjie-4-127', '11939809-mengjie', '8-76-mengjie', 'mengjie-4-81', '2-404-mengjie', '6152959-mengjie', '6560428-mengjie', 'mengjie-4-177', '16237079-mengjie', '8-99-mengjie', 'mengjie-4-103', '6-75-mengjie', '2-474-mengjie', '6-184-mengjie', '8-37-mengjie', 'mengjie-4-15', '2-509-mengjie', '12318040-mengjie', '6314630-mengjie', '8-40-mengjie', '8-42-mengjie', '17217711-mengjie', '6-20-mengjie', '8-60-mengjie', 'mengjie-4-23', '6-94-mengjie', '16384336-mengjie', '6-55-mengjie', '6-93-mengjie', '8-84-mengjie', '16355718-mengjie', '6-110-mengjie', '17185101-mengjie', '14347863-mengjie', '2-494-mengjie', 'mengjie-4-143', '6-126-mengjie', 'mengjie-4-74', '6-178-mengjie', '6-57-mengjie', '12621315-mengjie', '2-23-mengjie', '6-133-mengjie',

In [2]:
# with open("C:/Users/Wenjuan.Zhang/Downloads/true_files.txt", "r", encoding="utf-8") as f:
#     true_files = [line.strip() for line in f if line.strip()]  # 去掉换行/空行

# cleaned_list = [os.path.splitext(os.path.basename(f))[0] for f in file_list]
# print(cleaned_list)
# # 过滤 file_list
# indices = [i for i, f in enumerate(cleaned_list) if f in true_files]
# matched_files = [file_list[i] for i in indices]



# print(f"共有 {len(matched_files)} 个文件符合条件")
# print(matched_files)



# cleaned_list = [os.path.splitext(os.path.basename(f))[0] for f in matched_files]
# print(cleaned_list)
# # 过滤 file_list
# filtered_files = [f for f in cleaned_list if f in true_files]

# print(f"共有 {len(filtered_files)} 个文件符合条件")
# print(filtered_files)

In [3]:
# with open("C:/Users/Wenjuan.Zhang/Downloads/true_files.txt", "r", encoding="utf-8") as f:
#     true_files = [line.strip() for line in f if line.strip()]  # 去掉换行/空行

# cleaned_list = [os.path.splitext(os.path.basename(f))[0] for f in file_list]
# print(cleaned_list)
# # 过滤 file_list
# filtered_files = [f for f in cleaned_list if f in true_files]

# print(f"共有 {len(filtered_files)} 个文件符合条件")
# print(filtered_files)


In [4]:

# Filter the list to only keep strings that contain uppercase letters
filtered_entity_types = [entity for entity in unique_entity_types if any(char.isupper() for char in entity)]
entity_type_mapping = {entity.lower(): entity for entity in unique_entity_types}
# Print the filtered list
print(filtered_entity_types)
# List to be changed
to_change = ["ae", "drug"]

# Change the strings to the one with uppercase letters according to filtered_entity_types
changed_list = [entity for entity in filtered_entity_types if entity.lower() in to_change]
print(changed_list)


filtered_entity_types_lower = [entity.lower() for entity in filtered_entity_types]

[]
[]


In [5]:
# removed_entity = ["SYM","ae-infectious","ae=infection<","ae\metabolism","bsym.sleeping","drug)lanuts<",
#                   "drug)methadone<","drug)morphine","drug)morphine<","lab=inflammatory","p=literature",
#                   "sDx"]

entities_with_low_count = [entity_type for entity_type, count in entity_type_counts.items() if count < 10]

# Print the list of entities with count < 10
print(entities_with_low_count)

[]


In [6]:

import re
import spacy
import html
import os
import random
import json

def split_sentences(nlp, text):
    """
    Splits the given text into sentences using spaCy's sentence segmenter.
    """
    doc = nlp(text)
    return [sent.text for sent in doc.sents]

def read_and_process_json_sections(json_file, nlp):
    global skipped_file
    """
    Reads a JSON file, processes sections into sentences, and maps mentions to sentences.
    """
    with open(json_file, "r", encoding="utf-8") as file:
        data = json.load(file)

    # Process each page in the JSON data
    final_data = []
    for page_id, page_content in enumerate(data['pages']):
        print(f"\033[91mProcessing\033[0m Page ID: {page_id}")

        # Clean the content by replacing </p> with a space and removing <p> tags
        cleaned_content = re.sub(r'<\/?p>', '', page_content)
        cleaned_content = re.sub(r'[\r\n\u21B5]+', ' ', page_content)
        # Extract entities from annotations
        entities = []
        for annotation in data['annotations']:
            if annotation['relationships']['date']['page']== page_id:
                start = annotation['textContext']['start']
                end = annotation['textContext']['end']
                entity_type = annotation['label']
                mention_text = cleaned_content[start:end]
                # Append the entity tuple
                entities.append({
                    "start": start,
                    "end": end,
                    "type": entity_type.lower(),
                    "text": annotation['textContext']['text']
                })
                

        # Order entities based on the value of start
        entities = sorted(entities, key=lambda x: x['start'])
        print(f"Entities: {entities}")

        # Split the section into sentences
        sentences = split_sentences(nlp, cleaned_content)

        sentence_start = 0
        entity_index = 0  # Index to track the current entity being processed
        num_entities = len(entities)

        for sentence in sentences:
            sentence_end = sentence_start + len(sentence)
            sentence_entities = []

            # Process entities that belong to the current sentence
            while entity_index < num_entities and entities[entity_index]["start"] >= sentence_start and entities[entity_index]["end"] <= sentence_end:
                entity = entities[entity_index]
                # print(f"Entity: {entity}")
                # Calculate relative start and end positions in the sentence
                relative_start = entity["start"] - sentence_start
                relative_end = entity["end"] - sentence_start
                entity_text = entity["text"]
                start = sentence.find(entity_text)

                # Validate that the extracted text matches the entity text
                if start != -1:
                    end = start + len(entity_text)
                    entity_type = entity["type"]
                    global unique_entity_types
                    global entity_type_counts
                    unique_entity_types.add(entity_type)
                    if entity_type in entity_type_counts:
                        entity_type_counts[entity_type] += 1
                    else:
                        entity_type_counts[entity_type] = 1
                    # if entity["type"] != "R/O" and entity["type"] != "sDx" and entity["type"] != "SYM" and entity["type"] != "Dx":
                    #     if entity["type"] in ["sDrug","cDrug", "drug"]:
                    #         sentence_entities.append((start, end, "Drug"))
                    #         print(f"\033[91mchanged to Drug: {entity['type']} at ({start}, {end}), and the word is {entity_text}\033[0m")
                    #     elif entity["type"] == "mAE" or entity["type"] == "ae":
                    #         sentence_entities.append((start, end, "AE"))
                    #         print(f"\033[91mchanged to AE: {entity['type']} at ({start}, {end}, and the word is {entity_text})\033[0m")
                    #     else:
                    #         sentence_entities.append((start, end, entity_type))
                    # else:
                    #     # print(f"\033[93mskip these entities: {entity['type']} at ({start}, {end})\033[0m")
                    #     skipped_file += 1
                        # print(f"skip these entities: {entity["type"]} at ({start}, {end})")
                    # sentence_entities.append((start, end, entity_type))
                    # sentence_entities.append((start, end, entity_type, entity_text))
                    # print(f"Entity matched: {entity_text} at ({start}, {end})")
                else:
                    print(
                        f"\033[93mWarning: Text mismatch for entity '{entity_text}' in {sentence} "
                        f"at indices ({relative_start}, {relative_end}).\033[0m" 
                    )

                # Move to the next entity
                entity_index += 1

            # Add the sentence and its entities to the labeled data
            if sentence_entities:
                final_data.append((sentence, {"entities": sentence_entities}))
                # print(f"\033[92mmatched Sentence: {sentence}\033[0m")
                # print(f"\033[92mmatched Entities: {sentence_entities}\033[0m")

            # Update the sentence_start for the next sentence
            if sentence_start + len(sentence) < len(cleaned_content) and cleaned_content[sentence_start + len(sentence)] == ' ':
                sentence_start = sentence_end + 1  # Account for the space/newline between sentences
            else:
                sentence_start = sentence_end

    return final_data

def get_file_list(folder_path):
    """
    Get a list of all JSON files in a folder.
    """
    return [os.path.join(folder_path, file) for file in os.listdir(folder_path) if file.endswith(".json")]


def split_file_list(file_list, train_ratio=0.8):
    """
    Split the list of files into train and test datasets.
    """
    random.seed(123)
    random.shuffle(file_list)
    split_idx = int(len(file_list) * train_ratio)
    return file_list[:split_idx], file_list[split_idx:]

def process_files(file_list, nlp):
    """
    Process JSON files into spaCy-compatible training data.
    """
    processed_data = []
    for json_file in file_list:
        print(f"\033[91mProcessing\033[0m file: {json_file}")
        processed_data.extend(read_and_process_json_sections(json_file, nlp))
    return processed_data
unique_entity_types = set()
entity_type_counts = {}
# Example usage
folder_path = 'C:/Users/Wenjuan.Zhang/OneDrive - FDA/Documents/Latest Annotation 07182025/FAERS_R1'  # Replace with your folder path
file_list = get_file_list(folder_path)

# Split into train and test datasets
train_files, test_files = split_file_list(file_list)

# Load a spaCy language model for sentence splitting
nlp = spacy.blank("en")
nlp.add_pipe("sentencizer")  # Add sentence segmenter
skipped_file = 0
# Process train and test files
train_data = process_files(train_files, nlp)
test_data = process_files(test_files, nlp)
print(test_files)
print(f"Skipped files: {skipped_file}")
# Output a sample from the formatted data
for sample in train_data[:3]:  # Display first 3 samples
    print(sample)
# Sort and print all unique entity types
sorted_unique_entity_types = sorted(unique_entity_types)
print(f"\033[92mUnique Entity Types: {sorted_unique_entity_types}\033[0m")
sorted_entity_type_counts = sorted(entity_type_counts.items())

# Print each key-value pair on a new line, separated by commas
for entity_type, count in sorted_entity_type_counts:
    print(f"{entity_type}: {count}")


# %%
import re
import spacy
import html
import os
import random
import json

def split_sentences(nlp, text):
    doc = nlp(text)
    return [sent.text for sent in doc.sents]

def read_and_process_json_sections(json_file, nlp, file_type):
    global skipped_file
    with open(json_file, "r", encoding="utf-8") as file:
        data = json.load(file)

    final_data = []

    for page_id, page_content in enumerate(data['pages']):
        # Replace <p>, </p> and \n with spaces
        cleaned_content = re.sub(r'</?p>', ' ', page_content)
        cleaned_content = re.sub(r'\n', ' ', cleaned_content)
        cleaned_content = re.sub(r'[\r\n\u21B5]+', ' ', cleaned_content)

        # Extract and filter entities
        entities = []
        for annotation in data['annotations']:
            if annotation['relationships']['date']['page'] != page_id:
                continue
            if annotation['note'] not in file_type:
                continue

            start = annotation['textContext']['start']
            end = annotation['textContext']['end']
            entity_type = annotation['label'].lower()
            mention_text = cleaned_content[start:end]

            # if entity_type in ["drug", "cdrug", "sdrug"]:
            #     entity_type = "drug"
            # elif entity_type == "mae":
            #     entity_type = "ae"
            # elif entity_type in ["fhx", "mhx"]:
            #     entity_type = "hx"

            # if entity_type not in ["vaccine","cause_of_death"]:
            if entity_type not in ["vaccine","family_history"]:
                entities.append({
                    "start": start,
                    "end": end,
                    "type": entity_type,
                    "text": annotation['textContext']['text']
                })

        # Sort entities by starting position
        entities.sort(key=lambda x: x['start'])

        sentences = split_sentences(nlp, cleaned_content)
        sentence_start = 0
        entity_index = 0
        num_entities = len(entities)

        for sentence in sentences:
            sentence_end = sentence_start + len(sentence)
            sentence_entities = []

            while (entity_index < num_entities and
                   sentence_start <= entities[entity_index]["start"] < sentence_end and
                   sentence_start <= entities[entity_index]["end"] <= sentence_end):

                entity = entities[entity_index]
                # entity_text = entity["text"]
                relative_start = entity["start"] - sentence_start
                relative_end = entity["end"] - sentence_start
                entity_text = cleaned_content[entity["start"]:entity["end"]]
                # Find the actual position of entity text in the sentence
                match_start = sentence.find(entity_text)
                print("entities:")
                print(cleaned_content[entity["start"]:entity["end"]])
                print(sentence[relative_start:relative_end])
                print(entity_text)
                if match_start != -1:
                    match_end = match_start + len(entity_text)
                    ent_type = entity["type"]

                    # Standardize case and match entity types
                    if ent_type.islower() and ent_type in filtered_entity_types_lower:
                        matched_type = [t for t in filtered_entity_types if t.lower() == ent_type][0]
                        print(f"\033[91mChanged to {matched_type}: {ent_type} at ({match_start}, {match_end}) with word '{entity_text}'\033[0m")
                        ent_type = matched_type

                    if ent_type not in entities_with_low_count:
                        unique_entity_types.add(ent_type)
                        entity_type_counts.setdefault(ent_type, 0)
                        entity_type_counts[ent_type] += 1

                        sentence_entities.append((
                            match_start, match_end, ent_type
                        ))
                    else:
                        print(f"\033[91mLow-count entity: {entity['type']} at ({match_start}, {match_end})\033[0m")
                else:
                    print(f"\033[93mWarning: Text mismatch for entity '{entity_text}' in sentence: \"{sentence}\" at ({relative_start}, {relative_end})\033[0m")

                entity_index += 1

            if sentence_entities:
                final_data.append((sentence, {"entities": sentence_entities}))

            # Update sentence start position for next iteration
            if sentence_start + len(sentence) < len(cleaned_content) and cleaned_content[sentence_start + len(sentence)] == ' ':
                sentence_start = sentence_end + 1
            else:
                sentence_start = sentence_end

    return final_data
def process_files(file_list, nlp, file_type):
    """
    Process JSON files into spaCy-compatible training data.
    """
    processed_data = []
    for json_file in file_list:
        # print(f"\033[91mProcessing\033[0m file: {json_file}")
        processed_data.extend(read_and_process_json_sections(json_file, nlp, file_type))
    return processed_data


# %%
print(len(train_files))
print(len(test_files))

# %%
###train data with SME1 and test data with SME1, too
train_data = process_files(train_files, nlp, ["ETHER"])  #"LLM","SME1"
test_data = process_files(test_files, nlp, ["ETHER"])
total_data = train_data + test_data
print(test_files)
print(f"Skipped files: {skipped_file}")
# Output a sample from the formatted data
for sample in train_data[:3]:  # Display first 3 samples
    print(sample)

# %%
print(entity_type_counts)

# %%
# import csv


# # 定义CSV的列名
# fieldnames = ["start", "end", "label", "text", "sentence", "origin_start", "origin_end", "origin_type", "origin_label", "json_file"]

# with open("C:/Users/Wenjuan.Zhang/OneDrive - FDA/Documents/total_data.csv", mode="w", newline="", encoding="utf-8") as file:
#     writer = csv.DictWriter(file, fieldnames=fieldnames)
#     writer.writeheader()  # 写入列名

#     for text, info in total_data:
#         for entity in info['entities']:
#             row = {
#                 "start": entity[0],
#                 "end": entity[1],
#                 "label": entity[2],
#                 "text": entity[3],
#                 "sentence":entity[4],
#                 "origin_start":entity[5],
#                 "origin_end":entity[6],
#                 "origin_type":entity[7],
#                 "origin_label":entity[8],
#                 "json_file": entity[9]
#             }
#             writer.writerow(row)  #


# %%

skipped_count = 0
remained_count = 0
exceedlength = 0
import warnings
from pathlib import Path
import spacy
from spacy.tokens import DocBin
from spacy.util import filter_spans
import re
from collections import defaultdict

def validate_entities(entities):
    """
    Validate that there are no overlapping entities.
    Args:
        entities (list): List of tuples (start, end, label).
    Returns:
        bool: True if no overlaps, False otherwise.
    """
    entities = sorted(entities, key=lambda x: x[0])  # Sort by start index
    for i in range(len(entities) - 1):
        if entities[i][1] > entities[i + 1][0]:  # Check for overlap
            return False
    return True

def clean_entities(entities, text):
    """
    Clean entity spans by removing leading and trailing whitespace.
    Args:
        entities (list): List of tuples (start, end, label).
        text (str): The text containing the entities.
    Returns:
        list: Cleaned list of entities.
    """
    cleaned_entities = []
    for start, end, label in entities:
        # Ensure start and end are within bounds
        start = max(0, min(start, len(text)))
        end = max(0, min(end, len(text)))
        
        # Remove leading whitespace
        while start < end and text[start].isspace():
            start += 1
        # Remove trailing whitespace
        while end > start and text[end - 1].isspace():
            end -= 1
        if start < end:
            cleaned_entities.append((start, end, label))
    return cleaned_entities

def split_sentences(nlp, text, entities):
    """
    Splits the given text into sentences using spaCy's sentence segmenter.
    If a sentence is longer than 512 characters, it is split at the closest whitespace to the left of the 512th character.
    Adjusts entity positions accordingly.
    """
    doc = nlp(text)
    sentences = [sent.text for sent in doc.sents]
    split_sentences = []
    split_entities = []

    for sentence in sentences:
        while len(sentence) > 512:
            # Find the closest whitespace to the left of the 512th character
            split_index = sentence.rfind(' ', 0, 512)
            if split_index == -1:
                split_index = 512  # If no whitespace is found, split at 512

            # Split the sentence at the whitespace
            part1 = sentence[:split_index].strip()
            part2 = sentence[split_index:].strip()
            split_sentences.append(part1)

            # Adjust entity positions
            part1_len = len(part1)
            part1_entities = []
            part2_entities = []
            for start, end, label in entities:
                if start < part1_len:
                    if end <= part1_len:
                        part1_entities.append((start, end, label))
                    else:
                        part1_entities.append((start, part1_len, label))
                        part2_entities.append((0, end - part1_len, label))
                else:
                    part2_entities.append((start - part1_len, end - part1_len, label))
            split_entities.append(part1_entities)
            sentence = part2
            entities = part2_entities

        split_sentences.append(sentence)
        split_entities.append(entities)

    return split_sentences, split_entities

def truncate_text_and_entities(text, entities, max_length=512):
    """
    Truncate text and entities to a maximum length.
    Args:
        text (str): The text to be truncated.
        entities (list): List of tuples (start, end, label).
        max_length (int): Maximum length of the text.
    Returns:
        tuple: Truncated text and entities.
    """
    global exceedlength
    if len(text) <= max_length:
        return text, entities

    truncated_text = text[:max_length]
    truncated_entities = []
    for start, end, label in entities:
        if start < max_length:
            if end > max_length:
                exceedlength += 1
                end = max_length
            truncated_entities.append((start, end, label))
    return truncated_text, truncated_entities

def convert(lang: str, TRAIN_DATA, output_path: Path):
    """
    Convert training data into SpaCy's .spacy format.
    Args:
        lang (str): Language code (e.g., "en").
        TRAIN_DATA (list): List of training data in the format [(text, {"entities": [...]})].
        output_path (Path): Path to save the .spacy file.
    """
    global skipped_count
    global remained_count
    nlp = spacy.blank(lang)  # Create a blank language model
    nlp.add_pipe("sentencizer")  # Add the sentencizer component to the pipeline
    db = DocBin()  # Initialize DocBin to store Doc objects
    entity_counts = defaultdict(int)
    for text, annot in TRAIN_DATA:
        # Split sentences and adjust entities
        sentences, entities_list = split_sentences(nlp, text, annot["entities"])
        for sentence, entities in zip(sentences, entities_list):
            # Truncate text and entities to the maximum length
            sentence, entities = truncate_text_and_entities(sentence, entities, max_length=512)
            doc = nlp.make_doc(sentence)  # Create a new Doc object
            
            # Validate entities for overlaps
            if not validate_entities(entities):
                skipped_count += 1
                warnings.warn(f"Skipping text with overlapping entities: {repr(sentence)}")
                continue
            
            # Clean entity spans
            entities = clean_entities(entities, sentence)
            
            ents = []
            for start, end, label in entities:
                span = doc.char_span(start, end, label=label, alignment_mode="strict")  #strict,expand
                if span is None:
                    skipped_count += 1
                    msg = (f"Skipping entity [{start}, {end}, {label}] in the text because the character span "
                           f"'{doc.text[start:end]}' does not align with token boundaries:\n\n{repr(sentence)}\n")
                    warnings.warn(msg)
                else:
                    remained_count += 1
                    print("Successfully added entity")
                    ents.append(span)
                    entity_counts[label] += 1
            filtered = filter_spans(ents) # THIS DOES THE TRICK
            if filtered:
                doc.ents = filtered  # Set the entities for the Doc
                db.add(doc)  # Add the Doc to DocBin

    db.to_disk(output_path)  # Save the DocBin to disk
    print(f"Saved to {output_path}")
    return entity_counts

# Example Usage

# Output paths
train_output_path = Path("C:/Users/Wenjuan.Zhang/OneDrive - FDA/Documents/train_FAVERS_R1_v1_ETHER_new_revision.spacy")
test_output_path = Path("C:/Users/Wenjuan.Zhang/OneDrive - FDA/Documents/valid_FAVERS_R1_v1_ETHER_new_revision.spacy")
total_output_path = Path("C:/Users/Wenjuan.Zhang/OneDrive - FDA/Documents/total_FAVERS_R1_v1_ETHER_new_revision.spacy")
# Convert and save to .spacy format
train_entity_counts = convert("en", train_data, train_output_path)
test_entity_counts = convert("en", test_data, test_output_path)
convert("en", total_data, total_output_path)

# %%

train_data


# %%
# Print the counts
print("Train Entity Counts:")
for entity_type, count in train_entity_counts.items():
    print(f"{entity_type}: {count}")

print("\nTest Entity Counts:")
for entity_type, count in test_entity_counts.items():
    print(f"{entity_type}: {count}")




Processing file: C:/Users/Wenjuan.Zhang/OneDrive - FDA/Documents/Latest Annotation 07182025/FAERS_R1\14726257-mengjie.json
Processing Page ID: 0
Entities: [{'start': 284, 'end': 295, 'type': 'temporal', 'text': '27-Mar-2018'}, {'start': 284, 'end': 295, 'type': 'date', 'text': '27-Mar-2018'}, {'start': 296, 'end': 317, 'type': 'symptom', 'text': 'concerned female'}, {'start': 296, 'end': 317, 'type': 'symptom', 'text': 'concerned female'}, {'start': 311, 'end': 317, 'type': 'sex', 'text': 'female'}, {'start': 337, 'end': 340, 'type': 'age', 'text': 'age'}, {'start': 355, 'end': 366, 'type': 'ae', 'text': 'hypotension'}, {'start': 355, 'end': 465, 'type': 'second_level_diagnosis', 'text': 'hypotension, tachycardia, acute lung injury, central nervous system disorder, hypoglycemia, metabolic acidosis'}, {'start': 355, 'end': 465, 'type': 'second_level_diagnosis', 'text': 'hypotension, tachycardia, acute lung injury, central nervous system disorder, hypoglycemia, metabolic acidosis'}, {'st

C:\Users\Wenjuan.Zhang\AppData\Local\Temp\1\ipykernel_19344\687472920.py:498: UserWarning: Skipping text with overlapping entities: 'J-Med-Toxicol 2016;12 (3):224-247), received on 27-Mar-2018 concerned on a female patient of unknown age who developed hypotension, tachycardia, acute lung injury, central nervous system disorder, hypoglycemia, metabolic acidosis, anion gap abnormal, hepatotoxicity, coagulopathy, acute kidney injury and rhabdomyolysis following treatment with tramadol, meloxicam and cyclobenzaprine.'
  warnings.warn(f"Skipping text with overlapping entities: {repr(sentence)}")
C:\Users\Wenjuan.Zhang\AppData\Local\Temp\1\ipykernel_19344\687472920.py:498: UserWarning: Skipping text with overlapping entities: 'Patient received tramadol, meloxicam and cyclobenzaprine and developed hypotension, tachycardia, acute lung injury, central nervous system disorder, hypoglycemia, metabolic acidosis, anion gap abnormal, hepatotoxicity, coagulopathy, acute kidney injury and rhabdomyolys

Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully

C:\Users\Wenjuan.Zhang\AppData\Local\Temp\1\ipykernel_19344\687472920.py:511: UserWarning: Skipping entity [55, 275, symptom] in the text because the character span 'rong/hard to complete tasks [PT: aphasia], could not drive for day, only driven short distances since/neurological issues [PT: impaired driving ability], vertigo/ dizzy/ headache too / headaches/ did have fewer headaches' does not align with token boundaries:

'words are right but looking at words they are spelled wrong/hard to complete tasks [PT: aphasia], could not drive for day, only driven short distances since/neurological issues [PT: impaired driving ability], vertigo/ dizzy/ headache too / headaches/ did have fewer headaches and her symptoms are getting worst/ nauseous/depth perception altered [PT: vertigo], having night flashes, they were more like diaphoresis, since her skin was cold but she was sweating/diaphoresis (calming but cold) [PT: cold sweat],'

  warnings.warn(msg)
C:\Users\Wenjuan.Zhang\AppData\Local\Te

Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully

...

Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully

C:\Users\Wenjuan.Zhang\AppData\Local\Temp\1\ipykernel_19344\687472920.py:498: UserWarning: Skipping text with overlapping entities: 'Non-company suspect medications included sil-norboral (oral, daily dose unknown, frequency unknown) for the treatment of type 2 diabetes mellitus buprenorphine (transdermal, daily dose unknown, frequency unknown) for the treatment of pain nos nadroparin calcium (subcutaneous, daily dose unknown, frequency unknown) for an unknown indication tramadol (unknown, daily dose unknown, frequency unknown) for an unknown indication.'
  warnings.warn(f"Skipping text with overlapping entities: {repr(sentence)}")
C:\Users\Wenjuan.Zhang\AppData\Local\Temp\1\ipykernel_19344\687472920.py:511: UserWarning: Skipping entity [51, 59, symptom] in the text because the character span 'migraine' does not align with token boundaries:

'Co-suspect drugs included: Aimovig (erenumab) for "migraineAllergan received the report on 29-APR-2019.The patient\'s medical history included "na

Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully

C:\Users\Wenjuan.Zhang\AppData\Local\Temp\1\ipykernel_19344\687472920.py:498: UserWarning: Skipping text with overlapping entities: 'On 18Sep2018 (also reported as 07Sep2018 and 19Sep2018), she was transferred from another hospital and readmitted with an increase of abdominal pain and skin rash.'
  warnings.warn(f"Skipping text with overlapping entities: {repr(sentence)}")
C:\Users\Wenjuan.Zhang\AppData\Local\Temp\1\ipykernel_19344\687472920.py:498: UserWarning: Skipping text with overlapping entities: 'She was hospitalized with possible toxic piroxicam reaction after starting baricitinib, possible dendritic cell tumor, APD (?)'
  warnings.warn(f"Skipping text with overlapping entities: {repr(sentence)}")
C:\Users\Wenjuan.Zhang\AppData\Local\Temp\1\ipykernel_19344\687472920.py:511: UserWarning: Skipping entity [13, 15, symptom] in the text because the character span '30' does not align with token boundaries:

'lymphocytes 730 (NR 1133-3105), eosinophils 150 (NR 28-273), basophils 20 (N

Saved to C:\Users\Wenjuan.Zhang\OneDrive - FDA\Documents\valid_FAVERS_R1_v1_ETHER_new_revision.spacy
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully added entity
Successfully ad

In [7]:
train_data

[('J-Med-Toxicol 2016;12 (3):224-247), received on 27-Mar-2018 concerned on a female patient of unknown age who developed hypotension, tachycardia, acute lung injury, central nervous system disorder, hypoglycemia, metabolic acidosis, anion gap abnormal, hepatotoxicity, coagulopathy, acute kidney injury and rhabdomyolysis following treatment with tramadol, meloxicam and cyclobenzaprine.',
  {'entities': [(60, 81, 'symptom'),
    (60, 81, 'symptom'),
    (119, 229, 'second_level_diagnosis'),
    (119, 229, 'second_level_diagnosis'),
    (251, 319, 'symptom'),
    (251, 319, 'symptom'),
    (345, 353, 'drug'),
    (345, 353, 'drug'),
    (355, 364, 'drug'),
    (355, 364, 'drug'),
    (369, 384, 'drug'),
    (369, 384, 'drug')]}),
 ('Patient received tramadol, meloxicam and cyclobenzaprine and developed hypotension, tachycardia, acute lung injury, central nervous system disorder, hypoglycemia, metabolic acidosis, anion gap abnormal, hepatotoxicity, coagulopathy, acute kidney injury and rh